In [1]:
import os
import copy
import pickle as pkl
import pandas as pd
from tqdm import tqdm
import random as random
import numpy as np
from ray import tune
import datasets
import numpy as np
from datasets import load_metric

from transformers import AutoTokenizer
from transformers import AutoModelForSequenceClassification
from transformers import TrainingArguments, Trainer
from datasets import load_dataset
from ray.tune.suggest.bayesopt import BayesOptSearch
from ray.tune.suggest.hyperopt import HyperOptSearch
from ray.tune.schedulers import ASHAScheduler
from pynvml import *

In [2]:
def print_gpu_utilization():
    nvmlInit()
    handle = nvmlDeviceGetHandleByIndex(0)
    info = nvmlDeviceGetMemoryInfo(handle)
    print(f"GPU memory occupied: {info.used//1024**2} MB.")


def print_summary(result):
    print(f"Time: {result.metrics['train_runtime']:.2f}")
    print(f"Samples/second: {result.metrics['train_samples_per_second']:.2f}")
    print_gpu_utilization()

In [3]:
    neg_to_pos_ratio = 1

    results_file = "results_titles_abstracts_gbdt.json"

    inputs = "titles_abstracts"

    filename_pos_human = "../data/pubmed_articles_pos_human.csv"
    filename_neg_human = "../data/pubmed_articles_neg_human.csv"

    with open("../data/cleaned_pos_neg_train_val_test_dataset_ids.pkl", "rb") as f:
        prop_typ_id_dict = pkl.load(f)
    ptype = 'is_consensus'



In [4]:
            pos_data_human = pd.read_csv(filename_pos_human, chunksize=100000)
            neg_data_human = pd.read_csv(filename_neg_human, chunksize=100000)

            pos_train_ids = prop_typ_id_dict[ptype]["pos"]["train"]
            neg_train_ids = prop_typ_id_dict[ptype]["neg"]["train"]

            pos_val_ids = prop_typ_id_dict[ptype]["pos"]["val"]
            neg_val_ids = prop_typ_id_dict[ptype]["neg"]["val"]

            pos_test_ids = prop_typ_id_dict[ptype]["pos"]["test"]
            neg_test_ids = prop_typ_id_dict[ptype]["neg"]["test"]

            pos_train_set = pd.DataFrame()
            pos_val_set = pd.DataFrame()
            pos_test_set = pd.DataFrame()

            for pos_chunk in tqdm(pos_data_human):

                indices = pos_chunk.index
                indices = list(indices)

                pos_train_indices = list(
                    set(indices).intersection(set(pos_train_ids))
                )
                pos_val_indices = list(set(indices).intersection(set(pos_val_ids)))
                pos_test_indices = list(set(indices).intersection(set(pos_test_ids)))

                pos_train_subset = pos_chunk.loc[pos_train_indices]
                if pos_train_set.empty:
                    pos_train_set = pd.DataFrame(columns=pos_train_set.columns)
                pos_train_set = pd.concat([pos_train_set, pos_train_subset])

                pos_val_subset = pos_chunk.loc[pos_val_indices]
                if pos_val_set.empty:
                    pos_val_set = pd.DataFrame(columns=pos_val_set.columns)
                pos_val_set = pd.concat([pos_val_set, pos_val_subset])

                pos_test_subset = pos_chunk.loc[pos_test_indices]
                if pos_test_set.empty:
                    pos_test_set = pd.DataFrame(columns=pos_test_set.columns)
                pos_test_set = pd.concat([pos_test_set, pos_test_subset])

            pos_train_set[ptype] = int(1)
            pos_val_set[ptype] = int(1)
            pos_test_set[ptype] = int(1)

            del pos_data_human
            del pos_train_subset
            del pos_chunk
            del indices
            del pos_train_ids

            neg_train_ids_sample = random.sample(
                neg_train_ids, round(len(pos_train_set) * neg_to_pos_ratio)
            )

            neg_train_set = pd.DataFrame()
            neg_val_set = pd.DataFrame()
            neg_test_set = pd.DataFrame()

            for neg_chunk in tqdm(neg_data_human):

                indices = neg_chunk.index
                indices = list(indices)
                neg_train_indices = list(
                    set(indices).intersection(set(neg_train_ids_sample))
                )
                neg_val_indices = list(set(indices).intersection(set(neg_val_ids)))
                neg_test_indices = list(set(indices).intersection(set(neg_test_ids)))
                neg_subset = neg_chunk.loc[indices]

                neg_train_subset = neg_chunk.loc[neg_train_indices]
                if neg_train_set.empty:
                    neg_train_set = pd.DataFrame(columns=neg_train_set.columns)
                neg_train_set = pd.concat([neg_train_set, neg_train_subset])

                neg_val_subset = neg_chunk.loc[neg_val_indices]
                if neg_val_set.empty:
                    neg_val_set = pd.DataFrame(columns=neg_val_set.columns)
                neg_val_set = pd.concat([neg_val_set, neg_val_subset])

                neg_test_subset = neg_chunk.loc[neg_test_indices]
                if neg_test_set.empty:
                    neg_test_set = pd.DataFrame(columns=neg_test_set.columns)
                neg_test_set = pd.concat([neg_test_set, neg_test_subset])

            neg_train_set[ptype] = int(0)
            neg_val_set[ptype] = int(0)
            neg_test_set[ptype] = int(0)

            del neg_data_human
            del neg_subset
            del neg_chunk
            del indices

            train_data = pd.concat([neg_train_set, pos_train_set]).sample(
                frac=1
            )
            del neg_train_set
            del pos_train_set
            val_data = pd.concat([neg_val_set, pos_val_set]).sample(frac=1)
            del neg_val_set
            del pos_val_set
            test_data = pd.concat([neg_test_set, pos_test_set]).sample(frac=1)
            del neg_test_set
            del pos_test_set

            y_train = train_data[ptype]
            y_val = val_data[ptype]
            y_test = test_data[ptype]
            if inputs == "abstracts":
                X_train = train_data["abstract_plaintext"]
                X_val = val_data["abstract_plaintext"]
                X_test = test_data["abstract_plaintext"]
            elif inputs == "titles":
                X_train = train_data["title"]
                X_val = val_data["title"]
                X_test = test_data["title"]
            elif inputs == "titles_abstracts":
                X_train = pd.Series(
                    [
                        "{0} {1}".format(train_title, train_abstract)
                        for train_title, train_abstract in zip(
                            train_data["title"], train_data["abstract_plaintext"]
                        )
                    ]
                )
                X_val = pd.Series(
                    [
                        "{0} {1}".format(val_title, val_abstract)
                        for val_title, val_abstract in zip(
                            val_data["title"], val_data["abstract_plaintext"]
                        )
                    ]
                )
                X_test = pd.Series(
                    [
                        "{0} {1}".format(test_title, test_abstract)
                        for test_title, test_abstract in zip(
                            test_data["title"], test_data["abstract_plaintext"]
                        )
                    ]
                )

            del train_data
            del val_data
            del test_data

19it [00:27,  1.47s/it]/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/tqdm/std.py:1195: DtypeWarning: Columns (14) have mixed types. Specify dtype option on import or set low_memory=False.
  for obj in iterable:
51it [01:13,  1.47s/it]/home/k2141255/anaconda3/envs/study_design_classifier/lib/python3.8/site-packages/tqdm/std.py:1195: DtypeWarning: Columns (14) have mixed types. Specify dtype option on import or set low_memory=False.
  for obj in iterable:
86it [02:02,  1.42s/it]
57it [01:41,  1.78s/it]


In [5]:
batch_size = 100000
# vectorizer = HashingVectorizer(ngram_range=(1, 4), stop_words="english")

In [6]:
train = pd.DataFrame()
train['label'] = y_train
train['text'] = list(X_train)

val = pd.DataFrame()
val['label'] = y_val
val['text'] = list(X_val)

test = pd.DataFrame()
test['label'] = y_test
test['text'] = list(X_test)

In [7]:
train_dataset = datasets.Dataset.from_pandas(train.reset_index(drop=True))
val_dataset = datasets.Dataset.from_pandas(val.reset_index(drop=True))
test_dataset = datasets.Dataset.from_pandas(test.reset_index(drop=True))

In [8]:
dataset = datasets.dataset_dict.DatasetDict(
{
    'train': train_dataset,
    'val': val_dataset,
    'test': test_dataset
})

In [9]:
tokenizer = AutoTokenizer.from_pretrained("bert-base-cased")


def tokenize_function(examples):

    return tokenizer(examples['text'], padding="max_length", truncation=True)


tokenized_datasets = dataset.map(tokenize_function, batched=True)

  0%|          | 0/10 [00:00<?, ?ba/s]

  0%|          | 0/271 [00:00<?, ?ba/s]

  0%|          | 0/301 [00:00<?, ?ba/s]

In [10]:
model = AutoModelForSequenceClassification.from_pretrained("bert-base-cased", num_labels=5)

Some weights of the model checkpoint at bert-base-cased were not used when initializing BertForSequenceClassification: ['cls.seq_relationship.weight', 'cls.predictions.transform.LayerNorm.weight', 'cls.predictions.transform.LayerNorm.bias', 'cls.predictions.decoder.weight', 'cls.seq_relationship.bias', 'cls.predictions.bias', 'cls.predictions.transform.dense.bias', 'cls.predictions.transform.dense.weight']
- This IS expected if you are initializing BertForSequenceClassification from the checkpoint of a model trained on another task or with another architecture (e.g. initializing a BertForSequenceClassification model from a BertForPreTraining model).
- This IS NOT expected if you are initializing BertForSequenceClassification from the checkpoint of a model that you expect to be exactly identical (initializing a BertForSequenceClassification model from a BertForSequenceClassification model).
Some weights of BertForSequenceClassification were not initialized from the model checkpoint at b

In [11]:
training_args = TrainingArguments(output_dir="test_trainer", evaluation_strategy="epoch", num_train_epochs=1, per_device_train_batch_size=64)

In [12]:
# print_gpu_utilization()

In [13]:
metric_acc = load_metric("accuracy")
metric_p = load_metric("precision")
metric_r = load_metric("recall")
metric_f = load_metric("f1")


In [14]:
def compute_metrics(eval_pred):

    logits, labels = eval_pred

    predictions = np.argmax(logits, axis=-1)
    
    acc = metric_acc.compute(predictions=predictions, references=labels)['accuracy']
    p = metric_p.compute(predictions=predictions, references=labels)['precision']
    r = metric_r.compute(predictions=predictions, references=labels)['recall']
    f = metric_f.compute(predictions=predictions, references=labels)['f1']
    
#     tune.report(f1 = f)

    return {'accuracy': acc, 'precision': p, 'recall': r, 'f1': f}

In [15]:
def model_init():
    return AutoModelForSequenceClassification.from_pretrained(
        'distilbert-base-uncased', return_dict=False, force_download=True)

In [16]:
small_train_dataset = tokenized_datasets["train"].shuffle(seed=42).select(range(50))
small_eval_dataset = tokenized_datasets["val"].shuffle(seed=42).select(range(50))
small_test_data = tokenized_datasets["test"].shuffle(seed=42).select(range(50))

In [17]:
train_dataset = tokenized_datasets["train"].shuffle(seed=42)
eval_dataset = tokenized_datasets["val"].shuffle(seed=42)
test_data = tokenized_datasets["test"].shuffle(seed=42)

In [18]:
train_dataset

Dataset({
    features: ['label', 'text', 'input_ids', 'token_type_ids', 'attention_mask'],
    num_rows: 9920
})

In [19]:
trainer = Trainer(

#     model=model,

    args=training_args,

    train_dataset=train_dataset,

    eval_dataset=eval_dataset,

    compute_metrics=compute_metrics,
    
    model_init=model_init

)

https://huggingface.co/distilbert-base-uncased/resolve/main/config.json not found in cache or force_download set to True, downloading to /home/k2141255/.cache/huggingface/transformers/tmpo9ynznl9


Downloading:   0%|          | 0.00/483 [00:00<?, ?B/s]

storing https://huggingface.co/distilbert-base-uncased/resolve/main/config.json in cache at /home/k2141255/.cache/huggingface/transformers/23454919702d26495337f3da04d1655c7ee010d5ec9d77bdb9e399e00302c0a1.91b885ab15d631bf9cee9dc9d25ece0afd932f2f5130eba28f2055b2220c0333
creating metadata file for /home/k2141255/.cache/huggingface/transformers/23454919702d26495337f3da04d1655c7ee010d5ec9d77bdb9e399e00302c0a1.91b885ab15d631bf9cee9dc9d25ece0afd932f2f5130eba28f2055b2220c0333
loading configuration file https://huggingface.co/distilbert-base-uncased/resolve/main/config.json from cache at /home/k2141255/.cache/huggingface/transformers/23454919702d26495337f3da04d1655c7ee010d5ec9d77bdb9e399e00302c0a1.91b885ab15d631bf9cee9dc9d25ece0afd932f2f5130eba28f2055b2220c0333
Model config DistilBertConfig {
  "_name_or_path": "distilbert-base-uncased",
  "activation": "gelu",
  "architectures": [
    "DistilBertForMaskedLM"
  ],
  "attention_dropout": 0.1,
  "dim": 768,
  "dropout": 0.1,
  "hidden_dim": 3072,

Downloading:   0%|          | 0.00/256M [00:00<?, ?B/s]

storing https://huggingface.co/distilbert-base-uncased/resolve/main/pytorch_model.bin in cache at /home/k2141255/.cache/huggingface/transformers/9c169103d7e5a73936dd2b627e42851bec0831212b677c637033ee4bce9ab5ee.126183e36667471617ae2f0835fab707baa54b731f991507ebbb55ea85adb12a
creating metadata file for /home/k2141255/.cache/huggingface/transformers/9c169103d7e5a73936dd2b627e42851bec0831212b677c637033ee4bce9ab5ee.126183e36667471617ae2f0835fab707baa54b731f991507ebbb55ea85adb12a
loading weights file https://huggingface.co/distilbert-base-uncased/resolve/main/pytorch_model.bin from cache at /home/k2141255/.cache/huggingface/transformers/9c169103d7e5a73936dd2b627e42851bec0831212b677c637033ee4bce9ab5ee.126183e36667471617ae2f0835fab707baa54b731f991507ebbb55ea85adb12a
Some weights of the model checkpoint at distilbert-base-uncased were not used when initializing DistilBertForSequenceClassification: ['vocab_layer_norm.bias', 'vocab_transform.weight', 'vocab_projector.weight', 'vocab_projector.bia

In [ ]:
best_trial = trainer.hyperparameter_search(
    direction="maximize",
    backend="ray",
    # Choose among many libraries:
    # https://docs.ray.io/en/latest/tune/api_docs/suggestion.html
    search_alg=HyperOptSearch(metric="eval_f1", mode="max"),
    # Choose among schedulers:
    # https://docs.ray.io/en/latest/tune/api_docs/schedulers.html
#     scheduler=ASHAScheduler(metric="f1", mode="max"),
    resources_per_trial = {'gpu':1}
)

huggingface/tokenizers: The current process just got forked, after parallelism has already been used. Disabling parallelism to avoid deadlocks...
To disable this warning, you can either:
	- Avoid using `tokenizers` before the fork if possible
	- Explicitly set the environment variable TOKENIZERS_PARALLELISM=(true | false)
huggingface/tokenizers: The current process just got forked, after parallelism has already been used. Disabling parallelism to avoid deadlocks...
To disable this warning, you can either:
	- Avoid using `tokenizers` before the fork if possible
	- Explicitly set the environment variable TOKENIZERS_PARALLELISM=(true | false)
huggingface/tokenizers: The current process just got forked, after parallelism has already been used. Disabling parallelism to avoid deadlocks...
To disable this warning, you can either:
	- Avoid using `tokenizers` before the fork if possible
	- Explicitly set the environment variable TOKENIZERS_PARALLELISM=(true | false)
huggingface/tokenizers: The 

2023-01-31 18:17:57,764	INFO trial_runner.py:803 -- starting _objective_968e481e


== Status ==
Current time: 2023-01-31 18:17:57 (running for 00:00:00.31)
Memory usage on this node: 56.9/62.6 GiB: ***LOW MEMORY*** less than 10% of the memory on this node is available for use. This can cause unexpected crashes. Consider reducing the memory used by your application or reducing the Ray object store size by setting `object_store_memory` when calling `ray.init`.
Using FIFO scheduling algorithm.
Resources requested: 1.0/16 CPUs, 1.0/1 GPUs, 0.0/5.37 GiB heap, 0.0/2.68 GiB objects (0.0/1.0 accelerator_type:G)
Result logdir: /home/k2141255/ray_results/_objective_2023-01-31_18-17-57
Number of trials: 1/20 (1 RUNNING)
+---------------------+----------+---------------------+-----------------+--------------------+-------------------------------+---------+
| Trial name          | status   | loc                 |   learning_rate |   num_train_epochs |   per_device_train_batch_size |    seed |
|---------------------+----------+---------------------+-----------------+--------------

Downloading: 100%|██████████| 483/483 [00:00<00:00, 1.02MB/s]
Downloading:   0%|          | 0.00/256M [00:00<?, ?B/s]
Downloading:   1%|          | 2.17M/256M [00:00<00:11, 22.8MB/s]
Downloading:   2%|▏         | 5.32M/256M [00:00<00:09, 28.8MB/s]
Downloading:   3%|▎         | 8.46M/256M [00:00<00:08, 30.6MB/s]
Downloading:   5%|▍         | 11.9M/256M [00:00<00:07, 32.9MB/s]
Downloading:   6%|▌         | 15.3M/256M [00:00<00:07, 33.8MB/s]
Downloading:   7%|▋         | 18.5M/256M [00:00<00:07, 33.4MB/s]
Downloading:   9%|▊         | 21.9M/256M [00:00<00:07, 33.9MB/s]
Downloading:  10%|▉         | 25.1M/256M [00:00<00:07, 32.9MB/s]
Downloading:  11%|█         | 28.3M/256M [00:00<00:08, 29.2MB/s]
Downloading:  12%|█▏        | 31.1M/256M [00:01<00:08, 28.5MB/s]
Downloading:  13%|█▎        | 34.2M/256M [00:01<00:07, 29.5MB/s]
Downloading:  15%|█▍        | 37.2M/256M [00:01<00:07, 30.1MB/s]
Downloading:  16%|█▌        | 40.3M/256M [00:01<00:07, 30.6MB/s]
Downloading:  17%|█▋        | 43.5M/2

== Status ==
Current time: 2023-01-31 18:18:04 (running for 00:00:06.58)
Memory usage on this node: 57.3/62.6 GiB: ***LOW MEMORY*** less than 10% of the memory on this node is available for use. This can cause unexpected crashes. Consider reducing the memory used by your application or reducing the Ray object store size by setting `object_store_memory` when calling `ray.init`.
Using FIFO scheduling algorithm.
Resources requested: 1.0/16 CPUs, 1.0/1 GPUs, 0.0/5.37 GiB heap, 0.0/2.68 GiB objects (0.0/1.0 accelerator_type:G)
Result logdir: /home/k2141255/ray_results/_objective_2023-01-31_18-17-57
Number of trials: 2/20 (1 PENDING, 1 RUNNING)
+---------------------+----------+---------------------+-----------------+--------------------+-------------------------------+---------+
| Trial name          | status   | loc                 |   learning_rate |   num_train_epochs |   per_device_train_batch_size |    seed |
|---------------------+----------+---------------------+-----------------+---

...

== Status ==
Current time: 2023-02-01 16:08:54 (running for 21:50:56.72)
Memory usage on this node: 59.5/62.6 GiB: ***LOW MEMORY*** less than 10% of the memory on this node is available for use. This can cause unexpected crashes. Consider reducing the memory used by your application or reducing the Ray object store size by setting `object_store_memory` when calling `ray.init`.
Using FIFO scheduling algorithm.
Resources requested: 1.0/16 CPUs, 1.0/1 GPUs, 0.0/5.37 GiB heap, 0.0/2.68 GiB objects (0.0/1.0 accelerator_type:G)
Result logdir: /home/k2141255/ray_results/_objective_2023-01-31_18-17-57
Number of trials: 2/20 (1 PENDING, 1 RUNNING)
+---------------------+----------+---------------------+-----------------+--------------------+-------------------------------+---------+
| Trial name          | status   | loc                 |   learning_rate |   num_train_epochs |   per_device_train_batch_size |    seed |
|---------------------+----------+---------------------+-----------------+---

(_objective pid=58786) 
 57%|█████▋    | 19322/33795 [18:14:56<13:41:03,  3.40s/it]
(_objective pid=58786) 
 57%|█████▋    | 19323/33795 [18:14:59<13:42:34,  3.41s/it]


== Status ==
Current time: 2023-02-01 16:08:59 (running for 21:51:01.72)
Memory usage on this node: 59.3/62.6 GiB: ***LOW MEMORY*** less than 10% of the memory on this node is available for use. This can cause unexpected crashes. Consider reducing the memory used by your application or reducing the Ray object store size by setting `object_store_memory` when calling `ray.init`.
Using FIFO scheduling algorithm.
Resources requested: 1.0/16 CPUs, 1.0/1 GPUs, 0.0/5.37 GiB heap, 0.0/2.68 GiB objects (0.0/1.0 accelerator_type:G)
Result logdir: /home/k2141255/ray_results/_objective_2023-01-31_18-17-57
Number of trials: 2/20 (1 PENDING, 1 RUNNING)
+---------------------+----------+---------------------+-----------------+--------------------+-------------------------------+---------+
| Trial name          | status   | loc                 |   learning_rate |   num_train_epochs |   per_device_train_batch_size |    seed |
|---------------------+----------+---------------------+-----------------+---

(_objective pid=58786) 
 57%|█████▋    | 19324/33795 [18:15:03<13:42:50,  3.41s/it]


== Status ==
Current time: 2023-02-01 16:09:04 (running for 21:51:06.72)
Memory usage on this node: 59.4/62.6 GiB: ***LOW MEMORY*** less than 10% of the memory on this node is available for use. This can cause unexpected crashes. Consider reducing the memory used by your application or reducing the Ray object store size by setting `object_store_memory` when calling `ray.init`.
Using FIFO scheduling algorithm.
Resources requested: 1.0/16 CPUs, 1.0/1 GPUs, 0.0/5.37 GiB heap, 0.0/2.68 GiB objects (0.0/1.0 accelerator_type:G)
Result logdir: /home/k2141255/ray_results/_objective_2023-01-31_18-17-57
Number of trials: 2/20 (1 PENDING, 1 RUNNING)
+---------------------+----------+---------------------+-----------------+--------------------+-------------------------------+---------+
| Trial name          | status   | loc                 |   learning_rate |   num_train_epochs |   per_device_train_batch_size |    seed |
|---------------------+----------+---------------------+-----------------+---

In [ ]:
outputs = trainer.predict(test_data)

In [ ]:
# best_trial = trainer.hyperparameter_search(
#     direction="maximize",
#     backend="ray",
#     # Choose among many libraries:
#     # https://docs.ray.io/en/latest/tune/api_docs/suggestion.html
#     search_alg=HyperOptSearch(metric="eval_f1", mode="max"),
#     # Choose among schedulers:
#     # https://docs.ray.io/en/latest/tune/api_docs/schedulers.html
# #     scheduler=ASHAScheduler(metric="f1", mode="max"),
#     resources_per_trial = {'gpu':1}
# )

In [ ]:
best_config = best_trial[-1]

In [ ]:
best_config['seed'] = int(best_config['seed'])

In [ ]:
training_args_final = TrainingArguments(output_dir="test_trainer", evaluation_strategy="epoch", **best_config)

In [ ]:
# trainer = Trainer(

# #     model=model,

#     args=training_args_final,

#     train_dataset=small_train_dataset,

#     eval_dataset=small_eval_dataset,

#     compute_metrics=compute_metrics,
    
#     model_init=model_init

# )

In [ ]:
# trainer.train()

In [42]:
outputs = trainer.predict(test_data)

The following columns in the test set don't have a corresponding argument in `DistilBertForSequenceClassification.forward` and have been ignored: text, token_type_ids. If text, token_type_ids are not expected by `DistilBertForSequenceClassification.forward`,  you can safely ignore this message.
***** Running Prediction *****
  Num examples = 300400
  Batch size = 8


In [43]:
outputs

PredictionOutput(predictions=array([[-0.4235383 ,  0.06483941],
       [-0.20529081, -0.14936392],
       [ 0.5272295 , -0.7910747 ],
       ...,
       [ 0.5491661 , -0.822238  ],
       [ 0.23855244, -0.579521  ],
       [ 0.44355652, -0.65753853]], dtype=float32), label_ids=array([0, 0, 0, ..., 0, 0, 0]), metrics={'test_loss': 0.2635432779788971, 'test_accuracy': 0.891707723035952, 'test_precision': 0.015689487739742655, 'test_recall': 0.8433931484502447, 'test_f1': 0.030805899001936535, 'test_runtime': 128396.3802, 'test_samples_per_second': 2.34, 'test_steps_per_second': 0.292})

In [44]:
predictions = np.argmax(outputs.predictions, axis=-1)

In [45]:
predictions

array([1, 1, 0, ..., 0, 0, 0])

In [48]:
labels = test_data['label']

In [49]:
acc = metric_acc.compute(predictions=predictions, references=labels)['accuracy']
p = metric_p.compute(predictions=predictions, references=labels)['precision']
r = metric_r.compute(predictions=predictions, references=labels)['recall']
f = metric_f.compute(predictions=predictions, references=labels)['f1']
    

In [50]:
acc

0.891707723035952

In [51]:
p

0.015689487739742655

In [52]:
r

0.8433931484502447

In [53]:
f

0.030805899001936535